# TTS baseline: ThonburianTTS vs Fish Audio S2-Pro
Zero-shot ไม่จูน — ดูความเป็นธรรมชาติ / prosody ภาษาไทย (และอังกฤษ)

ทั้ง 3 ส่วนรันแยกกันได้: **1** ThonburianTTS → **2** Fish S2-Pro → **3** Comparison (อ่านผลที่ 1–2 บันทึกไว้ใน `outputs/`)

| | ThonburianTTS | Fish Audio S2-Pro |
|---|---|---|
| Base | F5-TTS (flow matching) fine-tuned Thai | 5B Slow/Fast AR + codec |
| Prosody | จาก ref + วรรคตอน | inline tag `[whisper]` `[laughing]` |
| HW | CPU/GPU เล็กได้ | GPU ≥24GB |
| License | CC-BY-NC-SA | Fish Research (non-commercial) |

In [ ]:
# Test set 
test_sentences = [
    "สวัสดีครับ ยินดีที่ได้รู้จักนะครับ วันนี้อากาศดีมากเลย",
    "เมื่อวานฉันเดินไปตลาดตอนเช้า เจอป้าข้างบ้านขายมะม่วงน้ำดอกไม้ เลยซื้อมาสองกิโล หวานฉ่ำมาก กินแล้วนึกถึงสมัยเด็กๆ ที่บ้านคุณยายเลยล่ะ",
    "ว้าย! จริงเหรอ? ไม่อยากจะเชื่อเลย... ดีใจด้วยนะ เก่งมากๆ!",
    "ราคา 1,250 บาท โทร 081-234-5678 ภายในวันที่ 31 ตุลาคม 2569 เวลา 14:30 น.",
    "ประชุมทีม AI วันนี้ใช้ Zoom นะคะ ช่วยส่ง report ก่อนเที่ยง แล้วเจอกันที่ office ค่ะ",
    "Hello, nice to meet you. The weather is really lovely today, isn't it?",
    "ใหม่ไหมไม้ไม่ไหม้ ห้าคำนี้เสียงต่างกันแค่วรรณยุกต์",
    "นายกรัฐมนตรีแถลงว่ารัฐบาลจะเร่งแก้ไขปัญหาค่าครองชีพ และเพิ่มมาตรการช่วยเหลือประชาชนในทุกภูมิภาค",
    "ขอโทษนะคะ ไม่ทราบว่าสถานีรถไฟฟ้าอยู่ทางไหนคะ เดินไปไกลไหมคะ",
    "เสือกินเนื้อ เสื้อใส่เล่น เรือลอยน้ำ เหนือขึ้นไปมีเมฆ",
]
test_words = [
    "สวัสดี", "ขอบคุณ", "ประเทศไทย", "ข้าว", "ขาว",
    "เสือ", "เสื้อ", "คอมพิวเตอร์", "Wi-Fi", "computer",
]
TEXTS = {f"s{i+1:02d}": t for i, t in enumerate(test_sentences)} | {f"w{i+1:02d}": t for i, t in enumerate(test_words)}

In [2]:
# Shared config (รันก่อนทุกส่วน; ต้องรัน Test set ด้านบนก่อน)
import sys, time, subprocess, shutil
from pathlib import Path
import torch, soundfile as sf, pandas as pd
from IPython.display import Audio, display

def clone(url, d):
    if not Path(d).exists(): subprocess.run(["git", "clone", "-q", url, d], check=True)

OUT = Path("outputs"); OUT.mkdir(exist_ok=True)
DEVICE = "cuda" if torch.cuda.is_available() else "cpu"
if DEVICE == "cuda":
    p = torch.cuda.get_device_properties(0)
    print(f"cuda: {p.name} | {p.total_memory/2**30:.0f} GB")
else:
    print("cpu")

def run_cases(model, cases, synth):
    """synth(text, name) -> wav path. บันทึก metrics ลง outputs/<model>/metrics.csv"""
    d = OUT / model; d.mkdir(exist_ok=True); rows = []
    for name, text in cases.items():
        if DEVICE == "cuda": torch.cuda.reset_peak_memory_stats()
        t0 = time.time(); src = synth(text, name); el = time.time() - t0
        dst = d / f"{name}.wav"
        if Path(src) != dst: shutil.copy(src, dst)
        wav, sr = sf.read(dst); dur = len(wav) / sr
        rows.append(dict(case=name, audio_s=round(dur, 2), gen_s=round(el, 2), rtf=round(el / dur, 2),
                         vram_gb=round(torch.cuda.max_memory_allocated() / 2**30, 1) if DEVICE == "cuda" else None))
        print(f"{name}: {text}"); display(Audio(str(dst)))
    df = pd.DataFrame(rows); df.to_csv(d / "metrics.csv", index=False)
    return df

cuda: NVIDIA GeForce RTX 2050 | 4 GB


# 1. ThonburianTTS

In [3]:
# Setup: env 490-TTS ติดตั้งแล้ว -> เหลือแค่ clone  (Colab: %pip install -q f5-tts cached-path pydub librosa pythainlp)
clone("https://github.com/biodatlab/thonburian-tts.git", "thonburian-tts")

In [4]:
sys.path.insert(0, str(Path("thonburian-tts").resolve()))
from flowtts.inference import FlowTTSPipeline, ModelConfig, AudioConfig
from cached_path import cached_path

cfg = ModelConfig(
    language="th", model_type="F5", vocoder="vocos", device=DEVICE,
    checkpoint="hf://biodatlab/ThonburianTTS/megaF5/mega_f5_last.safetensors",
    vocab_file="hf://biodatlab/ThonburianTTS/megaF5/mega_vocab.txt",
)
tts_th = FlowTTSPipeline(model_config=cfg, audio_config=AudioConfig(cfg_strength=2.5, speed=1.0), temp_dir=str(OUT / "_tmp"))

# reference voice (เปลี่ยนเป็นไฟล์ตัวเองได้); REF_TEXT=None -> auto-transcribe
REF_AUDIO = str(cached_path("hf://ThuraAung1601/E2-F5-TTS/ref_samples/ref_sample.wav"))
REF_TEXT = tts_th.model.transcribe(REF_AUDIO)
print("ref text:", REF_TEXT); display(Audio(REF_AUDIO))

c:\Users\BM MONEY\miniconda3\envs\490-TTS\Lib\site-packages\tqdm\auto.py:21: TqdmWarning: IProgress not found. Please update jupyter and ipywidgets. See https://ipywidgets.readthedocs.io/en/stable/user_install.html
  from .autonotebook import tqdm as notebook_tqdm
W1031 18:17:43.665000 25408 site-packages\torch\distributed\elastic\multiprocessing\redirects.py:29] NOTE: Redirects are currently not supported in Windows or MacOs.


Download Vocos from huggingface charactr/vocos-mel-24khz

vocab :  D:\SLM-labs\SLM-Labs-SignDINO\PoC\Speech\hub\models--biodatlab--ThonburianTTS\snapshots\ac854d8b3d59dd240812ed486072c357e0f515b6\megaF5\mega_vocab.txt
token :  custom
model :  D:\SLM-labs\SLM-Labs-SignDINO\PoC\Speech\hub\models--biodatlab--ThonburianTTS\snapshots\ac854d8b3d59dd240812ed486072c357e0f515b6\megaF5\mega_f5_last.safetensors 



[transformers] `torch_dtype` is deprecated! Use `dtype` instead!
Loading weights: 100%|██████████| 587/587 [00:01<00:00, 454.57it/s]
[transformers] Using `chunk_length_s` is very experimental with seq2seq models. The results will not necessarily be entirely accurate and will have caveats. More information: https://github.com/huggingface/transformers/pull/20104. Ignore this warning with pipeline(..., ignore_warning=True). To use Whisper for long-form transcription, use rather the model's `generate` method directly as the model relies on its own chunking mechanism (cf. Whisper original paper, section 3.8. Long-form Transcription).
[transformers] Passing `generation_config` together with generation-related arguments=({'begin_suppress_tokens', 'suppress_tokens'}) is deprecated and will be removed in future versions. Please pass either a `generation_config` object OR all generation parameters explicitly, but not both.
[transformers] Ignoring clean_up_tokenization_spaces=True for BPE tokeniz

ref text: Kræpin púraf.


In [5]:
df_th = run_cases("thonburian", TEXTS,
    lambda text, name: tts_th(text, REF_AUDIO, str(OUT / f"_th_{name}.wav"), ref_text=REF_TEXT))
df_th

Converting audio...
Using custom reference text...

ref_text   Kræpin púraf. 
gen_text 0 สวัสดีครับ ยินดีที่ได้รู้จักนะครับ วันนี้อากาศดีมากเลย


Generating audio in 1 batches...


100%|██████████| 1/1 [00:07<00:00,  7.18s/it]

s01: สวัสดีครับ ยินดีที่ได้รู้จักนะครับ วันนี้อากาศดีมากเลย


Converting audio...
Using custom reference text...

ref_text   Kræpin púraf. 
gen_text 0 เมื่อวานฉันเดินไปตลาดตอนเช้า เจอป้าข้างบ้านขายมะม่วงน้ำดอกไม้ เลยซื้อมาสองกิโล หวานฉ่ำมาก กินแล้วนึกถึงสมัยเด็กๆ ที่บ้านคุณยายเลยล่ะ


Generating audio in 1 batches...


100%|██████████| 1/1 [00:16<00:00, 16.34s/it]

...

w09: Wi-Fi


Converting audio...
Using custom reference text...

ref_text   Kræpin púraf. 
gen_text 0 computer


Generating audio in 1 batches...


100%|██████████| 1/1 [00:02<00:00,  2.54s/it]

w10: computer


,case,audio_s,gen_s,rtf,vram_gb
0,s01,11.68,7.31,0.63,2.3
1,s02,28.57,16.40,0.57,2.3
2,s03,11.17,6.24,0.56,2.3
3,s04,10.06,5.74,0.57,2.3
4,s05,14.27,7.64,0.53,2.3
5,s06,5.16,3.57,0.69,2.2
6,s07,10.94,5.93,0.54,2.3
7,s08,20.94,12.13,0.58,2.3
8,s09,12.79,7.07,0.55,2.3
9,s10,11.32,6.24,0.55,2.3


# 2. Fish Audio S2-Pro
ต้องใช้ GPU ≥24GB (Colab A100/L4). ใช้ CLI ของ fish-speech: encode ref → text→semantic → decode. ใช้ ref เสียงเดียวกับส่วน 1

In [ ]:
# Setup (Colab/Linux, GPU ≥24GB). ถ้า weights ถูก gate: from huggingface_hub import login; login()
%pip install -q "huggingface_hub[cli]"
clone("https://github.com/fishaudio/fish-speech.git", "fish-speech")
%pip install -q -e ./fish-speech
if not Path("fish-speech/checkpoints/s2-pro").exists():
    subprocess.run(["hf", "download", "fishaudio/s2-pro", "--local-dir", "fish-speech/checkpoints/s2-pro"], check=True)

In [ ]:
from cached_path import cached_path
FISH = Path("fish-speech").resolve(); CKPT = FISH / "checkpoints/s2-pro"
if DEVICE == "cuda" and p.total_memory < 24 * 2**30: print("WARN: VRAM < 24GB, อาจ OOM")

# ถ้ารันส่วน 2 แยก: ตั้ง ref เอง (REF_AUDIO/REF_TEXT จากส่วน 1 ถูกใช้ถ้ามี)
REF_AUDIO = globals().get("REF_AUDIO") or str(cached_path("hf://ThuraAung1601/E2-F5-TTS/ref_samples/ref_sample.wav"))
REF_TEXT = globals().get("REF_TEXT") or "ใส่ transcript ของ REF_AUDIO ที่นี่"

def sh(*args, cwd):
    r = subprocess.run([sys.executable, *map(str, args)], cwd=cwd, capture_output=True, text=True)
    if r.returncode: raise RuntimeError(r.stderr[-1500:])

def fish_tts(text, name):
    w = OUT / f"_fish_{name}"; shutil.rmtree(w, ignore_errors=True); w.mkdir(parents=True)
    dac = FISH / "fish_speech/models/dac/inference.py"
    sh(dac, "-i", Path(REF_AUDIO).resolve(), "--checkpoint-path", CKPT / "codec.pth", "--device", DEVICE, cwd=w)
    sh(FISH / "fish_speech/models/text2semantic/inference.py", "--text", text, "--checkpoint-path", CKPT,
       "--device", DEVICE, "--prompt-text", REF_TEXT, "--prompt-tokens", "fake.npy", cwd=w)
    sh(dac, "-i", "codes_0.npy", "--checkpoint-path", CKPT / "codec.pth", "--device", DEVICE, cwd=w)
    return w / "fake.wav"

# inline tag ใช้ได้เฉพาะ Fish
FISH_TAGS = {
    "th_whisper": "[whisper] นี่เป็นความลับนะ อย่าบอกใครเด็ดขาดเลย",
    "th_laugh":   "[laughing] ฮ่าๆ ตลกมากเลย [pause] เล่าอีกทีสิ",
    "th_excited": "[excited] เย้! สอบผ่านแล้ว ดีใจที่สุดเลย!",
}
df_fish = run_cases("fish", {**TEXTS, **FISH_TAGS}, fish_tts)
df_fish

# 3. Comparison
อ่านผลจาก `outputs/<model>/` (ข้ามโมเดลที่ยังไม่ได้รัน). RTF < 1 = เร็วกว่า real-time

In [ ]:
models = [m for m in ("thonburian", "fish") if (OUT / m / "metrics.csv").exists()]
dfs = {m: pd.read_csv(OUT / m / "metrics.csv").set_index("case") for m in models}
display(pd.concat(dfs, axis=1).swaplevel(axis=1).sort_index(axis=1))  # metric -> model
print("missing:", {"thonburian", "fish"} - set(models) or "-")

In [ ]:
# ฟังเทียบทีละเคส
for case in TEXTS:
    print(f"== {case}: {TEXTS[case]}")
    for m in models: print(m); display(Audio(str(OUT / m / f"{case}.wav")))